Импорт библиотек

In [2]:
import pandas as pd
import numpy as np
import seaborn as sns
import matplotlib.pyplot as plt
import plotly.express as px
import warnings
warnings.filterwarnings('ignore')

from sklearn.model_selection import TimeSeriesSplit
from sklearn.metrics import mean_squared_log_error
from sklearn.linear_model import LinearRegression, Ridge
from sklearn.tree import DecisionTreeRegressor
from sklearn.ensemble import HistGradientBoostingRegressor
from sklearn.preprocessing import LabelEncoder

plt.style.use('seaborn-v0_8-pastel')
sns.set_palette("pink")
plt.rcParams['figure.figsize'] = (10, 6)
plt.rcParams['axes.facecolor'] = '#fff7f9'

Загрузка данных

In [3]:
df_train = pd.read_csv('train.csv', parse_dates=['date'])
df_test = pd.read_csv('test.csv', parse_dates=['date'])
df_holidays = pd.read_csv('holidays_events.csv', parse_dates=['date'])
df_oil = pd.read_csv('oil.csv', parse_dates=['date'])
df_stores = pd.read_csv('stores.csv')
df_trans = pd.read_csv('transactions.csv', parse_dates=['date'])
df_subm = pd.read_csv('sample_submission.csv')

print(f"Train: {df_train.shape}, Test: {df_test.shape}")

Train: (3000888, 6), Test: (28512, 5)


Общая информация о датасетах

In [4]:
for name, df in {
    "train": df_train,
    "test": df_test,
    "stores": df_stores,
    "oil": df_oil,
    "transactions": df_trans,
    "holidays": df_holidays
}.items():
    print(f"\n{name.upper()} — shape: {df.shape}")
    display(df.head())
    print(df.info())


TRAIN — shape: (3000888, 6)


,id,date,store_nbr,family,sales,onpromotion
0,0,2013-01-01,1,AUTOMOTIVE,0.0,0
1,1,2013-01-01,1,BABY CARE,0.0,0
2,2,2013-01-01,1,BEAUTY,0.0,0
3,3,2013-01-01,1,BEVERAGES,0.0,0
4,4,2013-01-01,1,BOOKS,0.0,0


<class 'pandas.core.frame.DataFrame'>
RangeIndex: 3000888 entries, 0 to 3000887
Data columns (total 6 columns):
 #   Column       Dtype         
---  ------       -----         
 0   id           int64         
 1   date         datetime64[ns]
 2   store_nbr    int64         
 3   family       object        
 4   sales        float64       
 5   onpromotion  int64         
dtypes: datetime64[ns](1), float64(1), int64(3), object(1)
memory usage: 137.4+ MB
None

TEST — shape: (28512, 5)


,id,date,store_nbr,family,onpromotion
0,3000888,2017-08-16,1,AUTOMOTIVE,0
1,3000889,2017-08-16,1,BABY CARE,0
2,3000890,2017-08-16,1,BEAUTY,2
3,3000891,2017-08-16,1,BEVERAGES,20
4,3000892,2017-08-16,1,BOOKS,0


<class 'pandas.core.frame.DataFrame'>
RangeIndex: 28512 entries, 0 to 28511
Data columns (total 5 columns):
 #   Column       Non-Null Count  Dtype         
---  ------       --------------  -----         
 0   id           28512 non-null  int64         
 1   date         28512 non-null  datetime64[ns]
 2   store_nbr    28512 non-null  int64         
 3   family       28512 non-null  object        
 4   onpromotion  28512 non-null  int64         
dtypes: datetime64[ns](1), int64(3), object(1)
memory usage: 1.1+ MB
None

STORES — shape: (54, 5)


...

<class 'pandas.core.frame.DataFrame'>
RangeIndex: 1218 entries, 0 to 1217
Data columns (total 2 columns):
 #   Column      Non-Null Count  Dtype         
---  ------      --------------  -----         
 0   date        1218 non-null   datetime64[ns]
 1   dcoilwtico  1175 non-null   float64       
dtypes: datetime64[ns](1), float64(1)
memory usage: 19.2 KB
None

TRANSACTIONS — shape: (83488, 3)


,date,store_nbr,transactions
0,2013-01-01,25,770
1,2013-01-02,1,2111
2,2013-01-02,2,2358
3,2013-01-02,3,3487
4,2013-01-02,4,1922


<class 'pandas.core.frame.DataFrame'>
RangeIndex: 83488 entries, 0 to 83487
Data columns (total 3 columns):
 #   Column        Non-Null Count  Dtype         
---  ------        --------------  -----         
 0   date          83488 non-null  datetime64[ns]
 1   store_nbr     83488 non-null  int64         
 2   transactions  83488 non-null  int64         
dtypes: datetime64[ns](1), int64(2)
memory usage: 1.9 MB
None

HOLIDAYS — shape: (350, 6)


,date,type,locale,locale_name,description,transferred
0,2012-03-02,Holiday,Local,Manta,Fundacion de Manta,False
1,2012-04-01,Holiday,Regional,Cotopaxi,Provincializacion de Cotopaxi,False
2,2012-04-12,Holiday,Local,Cuenca,Fundacion de Cuenca,False
3,2012-04-14,Holiday,Local,Libertad,Cantonizacion de Libertad,False
4,2012-04-21,Holiday,Local,Riobamba,Cantonizacion de Riobamba,False


<class 'pandas.core.frame.DataFrame'>
RangeIndex: 350 entries, 0 to 349
Data columns (total 6 columns):
 #   Column       Non-Null Count  Dtype         
---  ------       --------------  -----         
 0   date         350 non-null    datetime64[ns]
 1   type         350 non-null    object        
 2   locale       350 non-null    object        
 3   locale_name  350 non-null    object        
 4   description  350 non-null    object        
 5   transferred  350 non-null    bool          
dtypes: bool(1), datetime64[ns](1), object(4)
memory usage: 14.1+ KB
None


Проверка пропусков

In [5]:
def check_missing(df, name):
    miss = df.isna().mean() * 100
    miss = miss[miss > 0].sort_values(ascending=False)
    if not miss.empty:
        print(f"\n{name}: есть пропуски в {len(miss)} колонках")
        display(miss)
    else:
        print(f"\n{name}: нет пропусков")

In [6]:
for n, d in {"train": df_train, "test": df_test, "stores": df_stores,
             "oil": df_oil, "transactions": df_trans, "holidays": df_holidays}.items():
    check_missing(d, n)


train: нет пропусков

test: нет пропусков

stores: нет пропусков

oil: есть пропуски в 1 колонках


dcoilwtico    3.530378
dtype: float64


transactions: нет пропусков

holidays: нет пропусков


Проверка дубликатов

In [7]:
for n, d in {"train": df_train, "test": df_test}.items():
    print(f"{n}: {d.duplicated().sum()} дубликатов")

train: 0 дубликатов
test: 0 дубликатов


Распределение продаж

In [8]:
fig = px.histogram(df_train, x="sales", nbins=100, color_discrete_sequence=["#ff8fab"])
fig.update_layout(
    title="Распределение продаж",
    xaxis_title="Sales",
    yaxis_title="Количество наблюдений",
    plot_bgcolor="#fff7f9"
)
fig.show()

print("среднее значение продаж:", df_train['sales'].mean())
print("медиана:", df_train['sales'].median())
print("доля нулевых продаж:", (df_train['sales'] == 0).mean())

среднее значение продаж: 357.77574911261894
медиана: 11.0
доля нулевых продаж: 0.3129506999261552


Динамика общих продаж по датам

In [9]:
daily_sales = (
    df_train.groupby('date')['sales']
    .sum()
    .reset_index()
)

fig = px.line(
    daily_sales,
    x='date', y='sales',
    title='Динамика общих продаж по датам',
    color_discrete_sequence=["#ff69b4"]
)
fig.update_layout(plot_bgcolor="#fff7f9")
fig.show()

Средние продажи по типам магазинов

In [10]:
merged = df_train.merge(df_stores, on='store_nbr', how='left')
type_sales = merged.groupby('type')['sales'].mean().reset_index().sort_values('sales', ascending=False)

fig = px.bar(type_sales, x='type', y='sales', color='type',
             color_discrete_sequence=px.colors.sequential.Pinkyl_r,
             title='Средние продажи по типам магазинов')
fig.update_layout(showlegend=False)
fig.show()

Средние продажи по кластерам

In [11]:
cluster_sales = merged.groupby('cluster')['sales'].mean().reset_index()

fig = px.bar(cluster_sales, x='cluster', y='sales',
             color_discrete_sequence=["#ff80b0"],
             title='Средние продажи по кластерам')
fig.show()

Топ-15 товаров по средним продажам

In [12]:
family_sales = df_train.groupby('family')['sales'].mean().reset_index().sort_values('sales', ascending=False)

fig = px.bar(family_sales.head(15), x='family', y='sales',
             color='sales', color_continuous_scale='pinkyl',
             title='Топ 15 товаров по средним продажам')
fig.show()

Объединение с stores

In [13]:
df_train = df_train.merge(df_stores, on='store_nbr', how='left')
df_test = df_test.merge(df_stores, on='store_nbr', how='left')

Объединение с oil (цены на нефть)

In [14]:
df_oil = df_oil.set_index('date')['dcoilwtico'].fillna(method='ffill').fillna(method='bfill')
df_train = df_train.merge(df_oil, on='date', how='left')
df_test = df_test.merge(df_oil, on='date', how='left')

In [15]:
df_train['dcoilwtico'] = df_train['dcoilwtico'].fillna(df_train['dcoilwtico'].median())
df_test['dcoilwtico'] = df_test['dcoilwtico'].fillna(df_train['dcoilwtico'].median())

Объединение с transactions

In [16]:
df_trans_indexed = df_trans.set_index(['date', 'store_nbr'])['transactions']
df_train = df_train.merge(df_trans_indexed, on=['date', 'store_nbr'], how='left')
df_test = df_test.merge(df_trans_indexed, on=['date', 'store_nbr'], how='left')

In [17]:
df_train['transactions'] = df_train['transactions'].fillna(0)
df_test['transactions'] = df_test['transactions'].fillna(0)

Подготовка праздников (holidays)

In [18]:
holidays = df_holidays.copy()

In [19]:
holidays['is_holiday'] = 1

In [20]:
national = holidays[holidays['locale'] == 'National'][['date', 'is_holiday']]
regional = holidays[holidays['locale'] == 'Regional'][['date', 'locale_name', 'is_holiday']].rename(columns={'locale_name': 'state'})
local = holidays[holidays['locale'] == 'Local'][['date', 'locale_name', 'is_holiday']].rename(columns={'locale_name': 'city'})

Присоединение праздников к train и test

In [21]:
for df in [df_train, df_test]:
    df = df.merge(national, on='date', how='left')
    df = df.merge(regional, on=['date', 'state'], how='left', suffixes=('', '_reg'))
    df = df.merge(local, on=['date', 'city'], how='left', suffixes=('', '_loc'))
    df['is_holiday'] = df[['is_holiday', 'is_holiday_reg', 'is_holiday_loc']].max(axis=1).fillna(0).astype(int)
    df.drop(columns=['is_holiday_reg', 'is_holiday_loc'], inplace=True, errors='ignore')

Дата-функции

In [22]:
for df in [df_train, df_test]:
    df['year'] = df['date'].dt.year
    df['month'] = df['date'].dt.month
    df['day'] = df['date'].dt.day
    df['dayofweek'] = df['date'].dt.dayofweek
    df['is_weekend'] = (df['dayofweek'] >= 5).astype(int)
    df['weekofyear'] = df['date'].dt.isocalendar().week.astype(int)

Землетрясение 2016

In [23]:
earthquake = pd.to_datetime('2016-04-16')
for df in [df_train, df_test]:
    df['days_after_earthquake'] = (df['date'] - earthquake).dt.days.clip(0, 14)


Школьный сезон

In [24]:
df_train['school_season'] = 0
df_test['school_season'] = 0

In [25]:
for year in range(2013, 2018):
    start = f'{year}-08-15'
    end = f'{year}-09-15'
    mask_train = (df_train['date'] >= start) & (df_train['date'] < end)
    df_train.loc[mask_train, 'school_season'] = 1
    if year == 2017:
        mask_test = (df_test['date'] >= start) & (df_test['date'] < end)
        df_test.loc[mask_test, 'school_season'] = 1

Зарплатные дни (payday)

In [26]:
for df in [df_train, df_test]:
    df['payday'] = ((df['date'].dt.day == 15) | (df['date'].dt.is_month_end)).astype(int)

Фурье-признаки

In [27]:
# Fourier
for df in [df_train, df_test]:
    df['dayofyear'] = df['date'].dt.dayofyear
    df['sin_week'] = np.sin(2 * np.pi * df['dayofyear'] / 7)
    df['cos_week'] = np.cos(2 * np.pi * df['dayofyear'] / 7)
    df['sin_year'] = np.sin(2 * np.pi * df['dayofyear'] / 365)
    df['cos_year'] = np.cos(2 * np.pi * df['dayofyear'] / 365)

Функция добавления лагов и rolling

лаги — продажи X дней назад;
rolling features — средние и стандартные отклонения за последние N дней.

In [28]:
def add_lag_rolling_features(df):
    df = df.sort_values(['store_nbr', 'family', 'date'])
    group_cols = ['store_nbr', 'family']
    
    # Лаги
    for lag in [1, 3, 7, 14, 28, 365]:
        df[f'lag_{lag}'] = df.groupby(group_cols)['sales'].shift(lag)
    
    # Rolling
    for w in [7, 14, 28]:
        df[f'roll_mean_{w}'] = df.groupby(group_cols)['sales'].shift(1).rolling(window=w, min_periods=1).mean()
        df[f'roll_std_{w}']  = df.groupby(group_cols)['sales'].shift(1).rolling(window=w, min_periods=1).std()
    
    return df


Сначала train

In [29]:
df_train = add_lag_rolling_features(df_train)

Потом конкатенируем с test и применяем снова

In [30]:
df_full = pd.concat([df_train, df_test], ignore_index=True)
df_full = df_full.sort_values(['store_nbr', 'family', 'date'])
df_full = add_lag_rolling_features(df_full)

Разделяем обратно

In [31]:

df_train = df_full[df_full['date'] < '2017-08-16'].copy()
df_test  = df_full[df_full['date'] >= '2017-08-16'].copy()

Заполняем NaN

In [32]:
lag_roll_cols = [c for c in df_train.columns if ('lag_' in c) or ('roll_' in c)]
df_train[lag_roll_cols] = df_train[lag_roll_cols].fillna(0)
df_test[lag_roll_cols]  = df_test[lag_roll_cols].fillna(0)

Кодирование категориальных признаков

In [ ]:
from sklearn.preprocessing import LabelEncoder

# Список категориальных колонок
cat_cols = ['city', 'state', 'type', 'family', 'store_nbr']

# Словарь для сохранения энкодеров
encoders = {}

# Применяем LabelEncoder к каждой колонке
for col in cat_cols:
    le = LabelEncoder()
    combined = pd.concat([df_train[col], df_test[col]], axis=0).astype(str)
    le.fit(combined)
    
    df_train[col + '_enc'] = le.transform(df_train[col].astype(str))
    df_test[col + '_enc'] = le.transform(df_test[col].astype(str))
    
    encoders[col] = le

In [34]:
df_train = df_train.drop(columns=cat_cols)
df_test = df_test.drop(columns=cat_cols)

Логарифм продаж

In [35]:
df_train['sales_log'] = np.log1p(df_train['sales'])

Список фичей

In [36]:
features = [col for col in df_train.columns if col not in ['id', 'date', 'sales', 'sales_log']]
print(f"Используется {len(features)} признаков")
df_train.head()

Используется 35 признаков


,id,date,sales,onpromotion,cluster,dcoilwtico,transactions,year,month,day,...,roll_mean_14,roll_std_14,roll_mean_28,roll_std_28,city_enc,state_enc,type_enc,family_enc,store_nbr_enc,sales_log
0,0,2013-01-01,0.0,0,13,93.14,0.0,2013,1,1,...,0.000000,0.000000,0.000000,0.000000,18,12,3,0,0,0.000000
1,1782,2013-01-02,2.0,0,13,93.14,2111.0,2013,1,2,...,0.000000,0.000000,0.000000,0.000000,18,12,3,0,0,1.098612
2,3564,2013-01-03,3.0,0,13,92.97,1833.0,2013,1,3,...,1.000000,1.414214,1.000000,1.414214,18,12,3,0,0,1.386294
3,5346,2013-01-04,3.0,0,13,93.12,1863.0,2013,1,4,...,1.666667,1.527525,1.666667,1.527525,18,12,3,0,0,1.386294
4,7128,2013-01-05,5.0,0,13,53.38,1509.0,2013,1,5,...,2.000000,1.414214,2.000000,1.414214,18,12,3,0,0,1.791759


Модели

In [37]:
models = {
    'LinearRegression': LinearRegression(),
    'Ridge': Ridge(alpha=1.0),
    'DecisionTree': DecisionTreeRegressor(max_depth=10, random_state=42),
    'HistGradientBoosting': HistGradientBoostingRegressor(
        max_iter=300, max_depth=10, learning_rate=0.05, random_state=42
    )
}

In [38]:
features = df_train.columns.drop(['id', 'date', 'sales', 'sales_log'])

Кросс-валидация TimeSeriesSplit

In [39]:
tscv = TimeSeriesSplit(n_splits=3)
results = {}

for name, model in models.items():
    print(f"\n{name}")
    scores = []
    for fold, (train_idx, val_idx) in enumerate(tscv.split(df_train)):
        train_set = df_train.iloc[train_idx]
        val_set   = df_train.iloc[val_idx]
        
        X_train, y_train = train_set[features], train_set['sales_log']
        X_val,   y_val   = val_set[features],   val_set['sales_log']
        
        model.fit(X_train, y_train)
        pred_log = model.predict(X_val).clip(0)
        pred = np.expm1(pred_log)
        true = np.expm1(y_val)
        score = np.sqrt(mean_squared_log_error(true, pred))
        scores.append(score)
        print(f"Fold {fold+1}: RMSLE = {score:.4f}")
    
    avg_score = np.mean(scores)
    results[name] = avg_score
    print(f"{name} Average RMSLE: {avg_score:.4f}")

# Итог
print("\nитог")
for name, score in results.items():
    print(f"{name}: {score:.4f}")


LinearRegression
Fold 1: RMSLE = 2.0346
Fold 2: RMSLE = 2.0250
Fold 3: RMSLE = 2.4834
LinearRegression Average RMSLE: 2.1810

Ridge
Fold 1: RMSLE = 2.0346
Fold 2: RMSLE = 2.0250
Fold 3: RMSLE = 2.4834
Ridge Average RMSLE: 2.1810

DecisionTree
Fold 1: RMSLE = 0.4551
Fold 2: RMSLE = 0.4426
Fold 3: RMSLE = 0.4372
DecisionTree Average RMSLE: 0.4450

HistGradientBoosting
Fold 1: RMSLE = 0.4266
Fold 2: RMSLE = 0.4130
Fold 3: RMSLE = 0.4009
HistGradientBoosting Average RMSLE: 0.4135

итог
LinearRegression: 2.1810
Ridge: 2.1810
DecisionTree: 0.4450
HistGradientBoosting: 0.4135


Итоговые результаты

In [40]:
print("\n=== FINAL RESULTS ===")
for name, score in results.items():
    print(f"{name}: {score:.4f}")


=== FINAL RESULTS ===
LinearRegression: 2.1810
Ridge: 2.1810
DecisionTree: 0.4450
HistGradientBoosting: 0.4135
